# Structure Analysis & Visualization

This notebook loads and renders the **6N8R** and **8r3y** mmCIF structure file. It utilizes `py3Dmol` to visualize the protein in a cartoon representation colored by secondary structure, allowing for quick inspection of conformational features.

In [1]:
from pathlib import Path
import py3Dmol

In [2]:
DATA_DIR = Path("../../data/input")
ref_cif = DATA_DIR / "6N8R.cif"
apkc_complex = DATA_DIR / "8r3y.cif"

## 6N8R colored by secondary structure

In [35]:
def view_structure(cif_path, chain="A"):
    view = py3Dmol.view(
        width=800, height=500
    )  # Create a blank 3D viewer canvas

    view.addModel(ref_cif.read_text(), "cif")

    # Set style: Cartoon representation, colored by secondary structure (or light gray)
    view.setStyle({'cartoon': {'color': 'spectrum'}})

    view.zoomTo()
    return view


# Display the structure
if ref_cif.exists():
    fig = view_structure(ref_cif)
    fig.show()
else:
    print(f"File not found at {ref_cif}. Update path to your structural data.")

3Dmol.js failed to load for some reason. Please check your browser console for error messages.

## Highlight specific residues 6N8R

In [36]:
def view_structure_with_sites(cif_path, target_sites, chain="A"):
    view = py3Dmol.view(width=800, height=500)

    view.addModel(cif_path.read_text(), "cif")

    # Base cartoon style for the whole protein
    view.setStyle({"chain": chain}, {"cartoon": {"color": "lightgrey"}})

    # Highlight specific target/anchor residues in bright sticks/spheres
    for site in target_sites:
        view.addStyle(
            {"chain": chain, "resi": str(site)},
            {"stick": {"colorscheme": "phosphorous"}},
        )

    view.zoomTo()
    return view


# Example: Highlight regulatory residues or anchor points
fig_sites = view_structure_with_sites(ref_cif, target_sites=[100, 150], chain="A")
fig_sites.show()

3Dmol.js failed to load for some reason. Please check your browser console for error messages.

## Layering Multiple Styles (Cartoon + Sticks)

In [38]:
view = py3Dmol.view(width=800, height=500)

view.addModel(ref_cif.read_text(), "cif")

# 1. Background protein as a subtle gray cartoon
view.setStyle({"cartoon": {"color": "lightgrey"}})

# 2. Highlight specific regulatory residues as distinct colored sticks
view.addStyle(
    {"resi": "100-150"},  # Select a specific residue range
    {"stick": {"colorscheme": "phosphorous", "radius": 0.2}},
)

view.zoomTo()
view.show()

3Dmol.js failed to load for some reason. Please check your browser console for error messages.

## Adding Molecular Surfaces (addSurface)

In [15]:
view.addSurface(
    py3Dmol.VDW,
    {
        "opacity": 0.6,
        "color": "yellow",
    },
    {"chain": "A"},
)

3Dmol.js failed to load for some reason. Please check your browser console for error messages.

## Side-by-Side Model Comparison

In [39]:
# Initialize side-by-side grid (1 row, 2 columns)
view = py3Dmol.view(width=900, height=500, viewergrid=(1, 2))

# ==========================================
# Left Pane (0, 0): Tier 1 - 6N8R + Reference Model
# ==========================================
view.addModel(ref_cif.read_text(), "cif", viewer=(0, 0))
view.setStyle({"viewer": (0, 0)}, {"cartoon": {"color": "spectrum"}})

# ==========================================
# Right Pane (0, 1): Tier 2 - 8r3y Complex
# ==========================================
view.addModel(apkc_complex.read_text(), "cif", viewer=(0, 1))

# Color-code individual chains in the complex
view.setStyle({"viewer": (0, 1), "chain": "I"}, {"cartoon": {"color": "salmon"}})  # aPKC
view.setStyle(
    {"viewer": (0, 1), "chain": "P"}, {"cartoon": {"color": "skyblue"}}
)  # Par-6
view.setStyle(
    {"viewer": (0, 1), "chain": "L"}, {"cartoon": {"color": "lightgreen"}}
)  # Lgl substrate

# Zoom each pane explicitly and render
view.zoomTo(viewer=(0, 0))
view.zoomTo(viewer=(0, 1))
view.show()

3Dmol.js failed to load for some reason. Please check your browser console for error messages.

## Highlighting Binding Pockets via Distance Selections (within)

In [40]:
# Style aPKC as a transparent surface, but highlight interface residues within 5Å of chain L as sticks
view.setStyle({"chain": "I"}, {"cartoon": {"color": "lightgrey"}})
view.addStyle(
    {
        "chain": "I",
        "within": {"distance": 5.0, "sel": {"chain": "L"}},
    },
    {"stick": {"colorscheme": "phosphorous"}},
)

3Dmol.js failed to load for some reason. Please check your browser console for error messages.

## Coloring by AlphaFold Confidence (pLDDT) or Custom Properties

In [28]:
view.setStyle(
    {"cartoon": {"colorscheme": {"prop": "b", "gradient": "sinebow", "min": 50, "max": 100}}}
)

3Dmol.js failed to load for some reason. Please check your browser console for error messages.

## Use the within selector to automatically highlight the binding interface residues between aPKC and Lgl

In [41]:
# Initialize viewer
view = py3Dmol.view(width=900, height=600)

# Load your local Tier 2 complex CIF file
view.addModel(apkc_complex.read_text(), "cif")

# 1. Set baseline styles for the complex
view.setStyle({"chain": "I"}, {"cartoon": {"color": "salmon"}})  # aPKC
view.setStyle({"chain": "P"}, {"cartoon": {"color": "skyblue"}})  # Par-6
view.setStyle(
    {"chain": "L"}, {"cartoon": {"color": "lightgreen"}, "opacity": 0.7}
)  # Lgl substrate

# 2. Highlight aPKC interface residues contacting Lgl (within 5.0 Angstroms)
interface_sel = {"chain": "I", "within": {"distance": 5.0, "sel": {"chain": "L"}}}

view.addStyle(
    interface_sel,
    {
        "stick": {"colorscheme": "phosphorous", "radius": 0.25},
        "cartoon": {"color": "red"},
    },
)

# 3. Automatically add text labels to those specific interface residues
view.addResLabels(
    interface_sel,
    {
        "fontColor": "black",
        "backgroundColor": "lightyellow",
        "backgroundOpacity": 0.8,
        "fontSize": 12,
    },
)

# Center, zoom, and render
view.zoomTo()
view.show()

3Dmol.js failed to load for some reason. Please check your browser console for error messages.